In [40]:
import pandas as pd
import numpy as np
import polars as pl
from functools import lru_cache
import sys
from sqlalchemy import create_engine
from sqlalchemy.engine import URL
import pymssql
from pathlib import Path

In [12]:
JY_CONFIG = {
    "server": "10.10.0.102",
    "user": "jydbReader",
    "password": "jy@9043!Reader",
    "database": "jydb",
    "charset": "cp936",
}
@lru_cache(maxsize=1)
def get_jy_conn():
    return pymssql.connect(**JY_CONFIG)

In [48]:
conn = get_jy_conn()
start_date = '2010-01-01'
end_date = '2026-09-30'

In [50]:
sql = f"""
SELECT
    s.SecuCode AS tick,
    d.TradingDay AS date,
    d.PE AS pe_ttm,
    d.PBLF AS pb_lf
FROM dbo.LC_DIndicesForValuation AS d
INNER JOIN dbo.SecuMain AS s
    ON d.InnerCode = s.InnerCode
WHERE s.SecuCategory = 1
  AND s.SecuMarket IN (83, 90)
  AND d.TradingDay BETWEEN '{start_date}' AND '{end_date}'

UNION ALL

SELECT
    s.SecuCode AS tick,
    d.TradingDay AS date,
    d.PETTM AS pe_ttm,
    d.PBLF AS pb_lf
FROM dbo.LC_STIBDIndiForValue AS d
INNER JOIN dbo.SecuMain AS s
    ON d.InnerCode = s.InnerCode
WHERE s.SecuCategory = 1
  AND s.SecuMarket IN (83, 90)
  AND d.TradingDay BETWEEN '{start_date}' AND '{end_date}'
"""

out = pl.read_database(
    query=sql,
    connection=conn,
)

In [51]:
dates = pd.to_datetime(np.load('Z:/axis/dates.npy',allow_pickle=True)).to_numpy(dtype="datetime64[ns]")
ticks = np.load('Z:/axis/stock_ticks.npy',allow_pickle=True)

In [53]:
pe_ttm = out.to_pandas().pivot(index='date', columns='tick', values='pe_ttm').reindex(index=dates, columns=ticks)
pe_ttm

tick,000001,000002,000004,000005,000006,000007,000008,000009,000010,000011,...,,,,,,,,,,
date,,,,,,,,,,,,,,,,,,,,,
2010-01-04,78.7940,24.7229,-83.7136,-475.2511,63.7397,49.0078,2622.9236,55.4528,184.6588,34.6693,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-05,77.4315,24.1631,-83.7136,-491.9127,61.9055,50.8465,2622.9236,54.0204,181.3752,33.5940,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-06,76.1022,24.1631,-83.7136,-482.3918,62.0775,50.8465,2622.9236,53.9693,183.2515,33.6917,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-07,75.2714,23.9766,-83.7136,-462.5566,61.5616,49.3614,2622.9236,54.9924,176.0591,32.9097,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-08,75.1052,24.1398,-83.7136,-467.3170,63.0519,49.7150,2622.9236,57.6525,179.1862,33.2356,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN


In [54]:
pe_ttm.values.astype(np.float32).tofile('Z:/stock/fundamental/valuation/pe_ttm.bin')

In [55]:
pb_lf = out.to_pandas().pivot(index='date', columns='tick', values='pb_lf').reindex(index=dates, columns=ticks)
pb_lf

tick,000001,000002,000004,000005,000006,000007,000008,000009,000010,000011,...,,,,,,,,,,
date,,,,,,,,,,,,,,,,,,,,,
2010-01-04,3.8573,3.3354,14.2179,7.3988,2.9917,-43.8112,12.2434,6.2440,37.8989,8.7496,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-05,3.7906,3.2599,14.2179,7.6582,2.9056,-45.4549,12.2434,6.0827,37.2250,8.4782,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-06,3.7255,3.2599,14.2179,7.5100,2.9137,-45.4549,12.2434,6.0769,37.6101,8.5029,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-07,3.6849,3.2347,14.2179,7.2012,2.8895,-44.1273,12.2434,6.1921,36.1339,8.3055,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2010-01-08,3.6767,3.2568,14.2179,7.2753,2.9595,-44.4434,12.2434,6.4917,36.7757,8.3877,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
NaT,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN


In [56]:
pb_lf.values.astype(np.float32).tofile('Z:/stock/fundamental/valuation/pb_lf.bin')

In [ ]:
import numpy as np

dates = np.load(r"Z:\axis\dates.npy", allow_pickle=True)
ticks = np.load(r"Z:\axis\stock_ticks.npy", allow_pickle=True)
n_dates = len(dates)

for field in [
    r"Z:\stock\m_essentials\amount.bin",
    r"Z:\stock\d_essentials\circ_mv.bin",
    r"Z:\stock\d_moneyflow\buy_lg_amount.bin",
    r"Z:\stock\d_moneyflow\sell_lg_amount.bin",
]:
    try:
        arr = np.memmap(
            field,
            dtype=np.float32,
            mode="r",
            shape=(len(dates), len(ticks)),  # 日频字段
        )
        valid = np.isfinite(arr).any(axis=1)
        positions = np.flatnonzero(valid)

        print(
            field,
            "最后有效日期:",
            dates[positions[-1]] if len(positions) else None,
            "9-30有效股票数:",
            int(np.isfinite(arr[n_dates - 1]).sum()),
        )
    except Exception as exc:
        print(field, type(exc).__name__, exc)

Z:\stock\m_essentials\amount.bin 最后有效日期: NaT 9-30有效股票数: 6447
Z:\stock\d_essentials\circ_mv.bin 最后有效日期: 2026-09-30 9-30有效股票数: 0
Z:\stock\d_moneyflow\buy_lg_amount.bin 最后有效日期: 2026-09-30 9-30有效股票数: 0
Z:\stock\d_moneyflow\sell_lg_amount.bin 最后有效日期: 2026-09-30 9-30有效股票数: 0


In [ ]:
arr = np.memmap(
    r"Z:\stock\d_essentials\circ_mv.bin",
    dtype=np.float32,
    mode="r",
    shape=(len(dates), len(ticks)),  # 日频字段
)

OSError: [WinError 8] 内存资源不足，无法处理此命令。

In [ ]:
import numpy as np

dates = np.load('/data/shanghai/xujiayi/workflow/data/axis/dates.npy',allow_pickle=True)
ticks = np.load('/data/shanghai/xujiayi/workflow/data/axis/stock_ticks.npy', allow_pickle=True)

valid_dates = dates[~np.isnat(dates)]
target = np.searchsorted(valid_dates, np.datetime64("2026-09-30"))

for offset in range(5):
    index = target - offset
    print("日期:", valid_dates[index])

    arr = np.memmap(
        r"/data/shanghai/xujiayi/workflow/data/stock/d_moneyflow/buy_lg_amount.bin",
        dtype=np.float32,
        mode="r",
        shape=(len(dates), len(ticks)),
    )

    row = arr[index]
    print(
        "有效股票数:",
        np.isfinite(row).sum(),
        "成交额:",
        np.nansum(row),
    )

日期: 2026-09-30


FileNotFoundError: [Errno 2] No such file or directory: 'Z:\\stock\\d_moneyflow\\buy_lg_amount.bin'